In [6]:
import logging
from typing import List, Dict, Any
import openrouter
import re

# Configure logging
logging.basicConfig(level=logging.INFO)
logger = logging.getLogger("GeminiAgent")

class GeminiAgent:
    def __init__(
        self,
        system_prompt: str,
        api_key: str,
        model_name: str = "google/gemini-1.5-pro",
    ):
        """
        Initializes the GeminiAgent with the specified system prompt and OpenRouter configurations.

        Args:
            system_prompt (str): The system-level instruction for the AI model.
            api_key (str): The API key for OpenRouter.
            model_name (str, optional): Name of the OpenRouter model to use. Defaults to "openrouter-gemini-1.5".
        """
        self.api_key = api_key
        self.model_name = model_name
        self.system_prompt = system_prompt

        # Initialize OpenRouter
        self.client = openrouter.OpenRouter(api_key=api_key)
        logger.info("OpenRouter initialized.")

        # Load the model
        self.model = self.client.get_model(model_name)
        logger.info(f"Model '{model_name}' loaded.")

        self.chat_session: openrouter.ChatSession = None
        logger.info("GeminiAgent initialized.")

    def start_session(self):
        """
        Starts a new chat session with the AI model.
        """
        self.chat_session = self.model.start_chat_session(self.system_prompt)
        logger.info("Chat session started with system prompt.")

    def parse_content_blocks(self, blocks: List[Dict[str, Any]]) -> (List[str], str):
        """
        Parses the response content blocks to extract text.

        Args:
            blocks (List[Dict[str, Any]]): The list of content blocks from the model.

        Returns:
            Tuple containing:
                - List of reasoning steps (strings).
                - Final answer string.
        """
        reasoning_steps = []
        final_answer = ""

        for block in blocks:
            text = block.get("text", "")
            thinking_text = re.findall(r"<thinking>(.*?)</thinking>", text, re.DOTALL)
            reasoning_steps.extend(thinking_text)
            if "<final_answer>" in text:
                final_answer = re.findall(r"<final_answer>(.*?)</final_answer>", text, re.DOTALL)[0]

        return reasoning_steps, final_answer

    def prompt(self, user_message: str) -> str:
        """
        Sends a user message to the AI model and returns the response.

        Args:
            user_message (str): The message from the user.

        Returns:
            str: The AI model's response.
        """
        if self.chat_session is None:
            raise ValueError("Please start a session before prompting the agent.")

        try:
            response = self.chat_session.send_message(user_message)
            logger.info(f"User: {user_message}")
            logger.debug(f"Raw Response: {response}")
            
            # Extract the text from the response
            response_text = response.get("text", "")
            logger.info(f"Assistant: {response_text}")
            return response_text
        except Exception as e:
            logger.error(f"Error sending message: {e}")
            return f"Error sending message: {e}"

import asyncio

async def generate_cot_structure(self, user_message: str):
    """
    Generates a chain-of-thought structure for the given user message.

    Args:
        user_message (str): The message from the user.

    Yields:
        dict: The generated chain-of-thought items.
    """
    if self.chat_session is None:
        raise ValueError("Please start a session before generating a chain-of-thought structure.")

    try:
        # Send the user message to the model
        response = self.chat_session.send_message(user_message)
        logger.info(f"User: {user_message}")
        logger.debug(f"Raw Response: {response}")

        # Extract the reasoning steps and final answer
        reasoning_steps, final_answer = self.parse_content_blocks(response.get("content", []))

        # Yield the chain-of-thought structure
        yield {"type": "cot_structure", "content": f"<thinking>\n{reasoning_steps}\n</thinking>"}

        # Yield each reasoning step
        for step in reasoning_steps:
            yield {"type": "step", "content": f"Thinking about: {step}"}
            # Simulate processing time for each step
            await asyncio.sleep(1)

        # Yield the final answer
        yield {"type": "response", "content": final_answer}

    except Exception as e:
        logger.error(f"Error generating content: {e}")
        yield {"type": "response", "content": f"Error generating content: {e}"}

async def generate_content(self, user_message: str):
    """
    Generates content based on the user message and yields the response.

    Args:
        user_message (str): The message from the user.

    Yields:
        str: The generated content.
    """
    if self.chat_session is None:
        raise ValueError("Please start a session before generating content.")

    try:
        # Send the user message to the model
        response = self.chat_session.send_message(user_message)
        logger.info(f"User: {user_message}")
        logger.debug(f"Raw Response: {response}")

        # Extract the text from the response
        response_text = response.get("text", "")
        logger.info(f"Assistant: {response_text}")
        yield response_text

    except Exception as e:
        logger.error(f"Error generating content: {e}")
        yield f"Error generating content: {e}"

In [13]:
from portkey_ai import Portkey
import textwrap
from rich.console import Console

# Initialize Portkey client with API key
client = Portkey(
    api_key="YGYPNo/brTCeuBU7iE9vbvyOnAFM"  # Replace with actual API key or use env variables
)

# Set up console for rich output
console = Console()

# Number of streams/buffers
NUM_STREAMS = 4
buffers = [""] * NUM_STREAMS

# Prompt ID for generating plan
GENERATE_PLAN = "pp-generate-p-f4a0de"

# Function to create a box around buffer content
def generate_box_around_buffer(buffer_text, buffer_num, max_cols=80):
    lines = buffer_text.split('\n')
    top_bottom_border = '+' + '-' * (max_cols - 2) + '+'
    boxed_text = [top_bottom_border]
    boxed_text.append(f"|{'Buffer ' + str(buffer_num):^{max_cols - 2}}|")
    boxed_text.append(top_bottom_border)
    
    for line in lines:
        wrapped_lines = textwrap.wrap(line, width=max_cols - 4)
        for wrapped_line in wrapped_lines:
            padded_line = wrapped_line.ljust(max_cols - 4)
            boxed_text.append(f"| {padded_line} |")
    
    boxed_text.append(top_bottom_border)
    return '\n'.join(boxed_text)

# Function to print current buffers
def print_buffers():
    for buffer_num, buffer in enumerate(buffers, start=1):
        boxed_output = generate_box_around_buffer(buffer, buffer_num)
        console.print(boxed_output, style="bold")
    console.print("\n\n\n\n")

# Create streaming prompt completion with n parallel responses
stream_prompt_completion = client.prompts.completions.create(
    prompt_id=GENERATE_PLAN,
    variables={"tools_available": "", "prompt": "Generate a multi-step plan for a project"},
    stream=True,
    n=NUM_STREAMS  # Request 4 completions in parallel
)

# Process and display the streamed completions
for idx, item in enumerate(stream_prompt_completion):
    for choice in item.choices:
        if "content" in choice.delta:
            # Append content to the appropriate buffer
            buffers[choice.index] += choice.delta["content"]
    
    # Print buffers periodically (every 10 streamed responses)
    if idx % 10 == 0:
        print_buffers()

# Print the final state of all buffers
print_buffers()


INFO:httpx:HTTP Request: POST https://api.portkey.ai/v1/prompts/pp-generate-p-f4a0de/completions "HTTP/1.1 200 OK"


+------------------------------------------------------------------------------+
|                                   Buffer 1                                   |
+------------------------------------------------------------------------------+
+------------------------------------------------------------------------------+

+------------------------------------------------------------------------------+
|                                   Buffer 2                                   |
+------------------------------------------------------------------------------+
+------------------------------------------------------------------------------+

+------------------------------------------------------------------------------+
|                                   Buffer 3                                   |
+------------------------------------------------------------------------------+
+------------------------------------------------------------------------------+

+------------------------------------------------------------------------------+
|                                   Buffer 4                                   |
+------------------------------------------------------------------------------+
+------------------------------------------------------------------------------+

...

+------------------------------------------------------------------------------+
|                                   Buffer 4                                   |
+------------------------------------------------------------------------------+
| ```xml                                                                       |
| <root>                                                                       |
|     <prompt>Generate a multi-step plan for a project</prompt>                |
|     <plan>                                                                   |
|         <START_OF_PLAN/>                                                     |
|         <steps>                                                              |
|             <step>                                                           |
|                 <plan_step_index>0</plan_step_index>                         |
|                 <step>Define the project's objectives and scope. This        |
| involves identifying the main goals, deliverables, target audience, and the  |
| overall vision of the project. It is crucial to document these elements      |
| clearly to guide the subsequent steps and ensure alignment among all         |
| stakeholders.</step>                                                         |
|                 <dependencies></dependencies>                                |
|             </step>                                                          |
|             <step>                                                           |
|                 <plan_step_index>1</plan_step_index>                         |
|                 <step>Conduct a feasibility study. This step involves        |
| assessing the technical, financial, and operational feasibility of the       |
| project. Gather data on the resources required, potential risks, and the     |
| projected return on investment. Compile a report summarizing the findings to |
| inform decision-making.</step>                                               |
|                 <dependencies></dependencies>                                |
|             </step>                                                          |
|             <step>                                                           |
|                 <plan_step_index>2</plan_step_index>                         |
|                 <step>Develop a detailed project plan. This includes         |
| creating a timeline, setting milestones, and assigning tasks to team         |
| members. Utilize project management tools to structure the plan and ensure   |
| that all tasks are tracked. Define the criteria for success and establish    |
| metrics for measuring progress.</step>                                       |
|                 <dependencies>                                               |
|                     <dependency>0</dependency>                               |
|                     <dependency>1</dependency>                               |
|                 </dependencies>                                              |
|             </step>                                                          |
|             <step>                                                           |
|                 <plan_step_index>3</plan_step_index>                         |
|                 <step>Assemble the project team. Identify the necessary      |
| skills and expertise required for the project and select team members        |
| accordingly. Conduct onboarding sessions to align the team with the project  |
| goals and plan. Clearly define roles and responsibilities for each team      |
| member.</step>                                                               |
|                 <dependencies>                                               |
|                     <dependency>2</dependency>                               |
|                 </dependencies>                                              |
|             </step>          

+------------------------------------------------------------------------------+
|                                   Buffer 1                                   |
+------------------------------------------------------------------------------+
| ```xml                                                                       |
| <root>                                                                       |
|     <prompt>Generate a multi-step plan for a project</prompt>                |
|     <plan>                                                                   |
|         <START_OF_PLAN/>                                                     |
|         <steps>                                                              |
|             <step>                                                           |
|                 <plan_step_index>0</plan_step_index>                         |
|                 <step>Identify the project's objective and scope. This       |
| involves defining the primary goals, deliverables, and the overall scope of  |
| the project. Gather initial requirements from stakeholders to understand     |
| their expectations and any constraints or limitations.</step>                |
|                 <dependencies></dependencies>                                |
|             </step>                                                          |
|             <step>                                                           |
|                 <plan_step_index>1</plan_step_index>                         |
|                 <step>Conduct a feasibility study. Assess the technical,     |
| economic, and operational feasibility of the project. This includes          |
| evaluating available resources, potential risks, and determining whether the |
| project is viable and worth pursuing.</step>                                 |
|                 <dependencies>                                               |
|                     <dependency>0</dependency>                               |
|                 </dependencies>                                              |
|             </step>                                                          |
|             <step>                                                           |
|                 <plan_step_index>2</plan_step_index>                         |
|                 <step>Create a detailed project plan. Outline the project's  |
| timeline, milestones, and specific tasks. Assign roles and responsibilities  |
| to team members and establish a project schedule with deadlines for each     |
| task. Ensure that the plan is realistic and accounts for potential risks and |
| delays.</step>                                                               |
|                 <dependencies>                                               |
|                     <dependency>0</dependency>                               |
|                     <dependency>1</dependency>                               |
|                 </dependencies>                                              |
|             </step>                                                          |
|             <step>                                                           |
|                 <plan_step_index>3</plan_step_index>                         |
|                 <step>Develop a risk management plan. Identify potential     |
| risks and their impact on the project. Develop strategies to mitigate these  |
| risks and create contingency plans. Ensure that all team members are aware   |
| of the risks and the plans in place to address them.</step>                  |
|                 <dependencies>                                               |
|                     <dependency>2</dependency>                               |
|                 </dependencies>                                              |
|             </step>                                                          |
|             <step>           

+------------------------------------------------------------------------------+
|                                   Buffer 2                                   |
+------------------------------------------------------------------------------+
| ```xml                                                                       |
| <root>                                                                       |
|     <prompt>Generate a multi-step plan for a project</prompt>                |
|     <plan>                                                                   |
|         <START_OF_PLAN/>                                                     |
|         <steps>                                                              |
|             <step>                                                           |
|                 <plan_step_index>0</plan_step_index>                         |
|                 <step>Define the project scope and objectives. This includes |
| identifying the main goals of the project, the key deliverables, and the     |
| criteria for success. Document the project requirements and constraints to   |
| ensure all stakeholders have a clear understanding of what the project aims  |
| to achieve.</step>                                                           |
|                 <dependencies></dependencies>                                |
|             </step>                                                          |
|             <step>                                                           |
|                 <plan_step_index>1</plan_step_index>                         |
|                 <step>Assemble the project team. Identify the key roles and  |
| responsibilities required for the project and select team members with the   |
| appropriate skills and expertise. Assign specific tasks to each team member  |
| and establish communication protocols to ensure effective                    |
| collaboration.</step>                                                        |
|                 <dependencies></dependencies>                                |
|             </step>                                                          |
|             <step>                                                           |
|                 <plan_step_index>2</plan_step_index>                         |
|                 <step>Create a detailed project plan. Break down the project |
| into smaller, manageable tasks and create a timeline for each task. Use      |
| project management tools such as Gantt charts or Kanban boards to visualize  |
| the project schedule and track progress. Ensure that dependencies between    |
| tasks are clearly identified to avoid delays.</step>                         |
|                 <dependencies>                                               |
|                     <dependency>0</dependency>                               |
|                     <dependency>1</dependency>                               |
|                 </dependencies>                                              |
|             </step>                                                          |
|             <step>                                                           |
|                 <plan_step_index>3</plan_step_index>                         |
|                 <step>Develop a risk management plan. Identify potential     |
| risks that could impact the project and assess their likelihood and impact.  |
| Develop mitigation strategies for each risk and assign responsibility for    |
| monitoring and managing risks throughout the project lifecycle.</step>       |
|                 <dependencies>                                               |
|                     <dependency>2</dependency>                               |
|                 </dependencies>                                              |
|             </step>                                                          |
|             <step>           

+------------------------------------------------------------------------------+
|                                   Buffer 3                                   |
+------------------------------------------------------------------------------+
| ```xml                                                                       |
| <root>                                                                       |
|   <prompt>Generate a multi-step plan for a project</prompt>                  |
|   <plan>                                                                     |
|     <START_OF_PLAN/>                                                         |
|     <steps>                                                                  |
|       <step>                                                                 |
|         <plan_step_index>0</plan_step_index>                                 |
|         <step>Define the project objectives and scope. This involves         |
| identifying the goals, deliverables, and constraints of the project. Clearly |
| outline what the project aims to achieve and the boundaries within which it  |
| will operate.</step>                                                         |
|         <dependencies></dependencies>                                        |
|       </step>                                                                |
|       <step>                                                                 |
|         <plan_step_index>1</plan_step_index>                                 |
|         <step>Identify the stakeholders and their requirements. Engage with  |
| all relevant parties, including clients, team members, and sponsors, to      |
| gather their expectations and needs. Document these requirements for         |
| reference throughout the project.</step>                                     |
|         <dependencies></dependencies>                                        |
|       </step>                                                                |
|       <step>                                                                 |
|         <plan_step_index>2</plan_step_index>                                 |
|         <step>Create a detailed project plan. Break down the project into    |
| manageable tasks and milestones. Assign responsibilities and set deadlines   |
| for each task. Use project management tools like Gantt charts or Kanban      |
| boards to visualize the timeline.</step>                                     |
|         <dependencies>                                                       |
|           <dependency>0</dependency>                                         |
|           <dependency>1</dependency>                                         |
|         </dependencies>                                                      |
|       </step>                                                                |
|       <step>                                                                 |
|         <plan_step_index>3</plan_step_index>                                 |
|         <step>Allocate resources and budget. Determine the resources (human, |
| financial, and material) required for the project. Develop a budget plan     |
| that includes all anticipated costs and ensure that resources are allocated  |
| efficiently.</step>                                                          |
|         <dependencies>                                                       |
|           <dependency>2</dependency>                                         |
|         </dependencies>                                                      |
|       </step>                                                                |
|       <step>                                                                 |
|         <plan_step_index>4</plan_step_index>                                 |
|         <step>Develop a risk management plan. Identify potential risks and   |
| uncertainties that could impa

+------------------------------------------------------------------------------+
|                                   Buffer 4                                   |
+------------------------------------------------------------------------------+
| ```xml                                                                       |
| <root>                                                                       |
|     <prompt>Generate a multi-step plan for a project</prompt>                |
|     <plan>                                                                   |
|         <START_OF_PLAN/>                                                     |
|         <steps>                                                              |
|             <step>                                                           |
|                 <plan_step_index>0</plan_step_index>                         |
|                 <step>Define the project's objectives and scope. This        |
| involves identifying the main goals, deliverables, target audience, and the  |
| overall vision of the project. It is crucial to document these elements      |
| clearly to guide the subsequent steps and ensure alignment among all         |
| stakeholders.</step>                                                         |
|                 <dependencies></dependencies>                                |
|             </step>                                                          |
|             <step>                                                           |
|                 <plan_step_index>1</plan_step_index>                         |
|                 <step>Conduct a feasibility study. This step involves        |
| assessing the technical, financial, and operational feasibility of the       |
| project. Gather data on the resources required, potential risks, and the     |
| projected return on investment. Compile a report summarizing the findings to |
| inform decision-making.</step>                                               |
|                 <dependencies></dependencies>                                |
|             </step>                                                          |
|             <step>                                                           |
|                 <plan_step_index>2</plan_step_index>                         |
|                 <step>Develop a detailed project plan. This includes         |
| creating a timeline, setting milestones, and assigning tasks to team         |
| members. Utilize project management tools to structure the plan and ensure   |
| that all tasks are tracked. Define the criteria for success and establish    |
| metrics for measuring progress.</step>                                       |
|                 <dependencies>                                               |
|                     <dependency>0</dependency>                               |
|                     <dependency>1</dependency>                               |
|                 </dependencies>                                              |
|             </step>                                                          |
|             <step>                                                           |
|                 <plan_step_index>3</plan_step_index>                         |
|                 <step>Assemble the project team. Identify the necessary      |
| skills and expertise required for the project and select team members        |
| accordingly. Conduct onboarding sessions to align the team with the project  |
| goals and plan. Clearly define roles and responsibilities for each team      |
| member.</step>                                                               |
|                 <dependencies>                                               |
|                     <dependency>2</dependency>                               |
|                 </dependencies>                                              |
|             </step>          

In [18]:
# # from portkey_ai import Portkey
# # import textwrap
# # from rich.console import Console
# # from rich.live import Live
# # from rich.layout import Layout
# # from rich.panel import Panel

# # # Initialize Portkey client with API key
# # client = Portkey(
# #     api_key="YGYPNo/brTCeuBU7iE9vbvyOnAFM"  # Replace with actual API key or use env variables
# # )

# # # Set up console for rich output
# # console = Console()

# # # Number of streams/buffers
# # NUM_STREAMS = 4
# # buffers = [""] * NUM_STREAMS

# # # Prompt ID for generating plan
# # GENERATE_PLAN = "pp-generate-p-f4a0de"

# # # Function to create a box around buffer content
# # def generate_box_around_buffer(buffer_text, buffer_num, max_cols=100):
# #     lines = buffer_text.split('\n')
# #     top_bottom_border = '+' + '-' * (max_cols - 2) + '+'
# #     boxed_text = [top_bottom_border]
# #     boxed_text.append(f"|{'Buffer ' + str(buffer_num):^{max_cols - 2}}|")
# #     boxed_text.append(top_bottom_border)
    
# #     for line in lines:
# #         wrapped_lines = textwrap.wrap(line, width=max_cols - 4)
# #         for wrapped_line in wrapped_lines:
# #             padded_line = wrapped_line.ljust(max_cols - 4)
# #             boxed_text.append(f"| {padded_line} |")
    
# #     boxed_text.append(top_bottom_border)
# #     return '\n'.join(boxed_text)

# # # Function to print current buffers in a grid layout
# # def create_layout():
# #     layout = Layout()

# #     # Split the layout into four vertical columns
# #     layout.split_row(
# #         Layout(name="buffer1"),
# #         Layout(name="buffer2"),
# #         Layout(name="buffer3"),
# #         Layout(name="buffer4")
# #     )

# #     return layout

# # # Update layout with buffers
# # def update_layout(layout):
# #     for i, buffer_content in enumerate(buffers):
# #         buffer_box = Panel(buffer_content, title=f"Buffer {i + 1}", border_style="bold")
# #         layout[f"buffer{i + 1}"].update(buffer_box)

# # # Create streaming prompt completion with n parallel responses
# # stream_prompt_completion = client.prompts.completions.create(
# #     prompt_id=GENERATE_PLAN,
# #     variables={"tools_available": "", "prompt": "Generate a multi-step plan for a project"},
# #     stream=True,
# #     max_tokens=1024,
# #     n=NUM_STREAMS  # Request 4 completions in parallel
# # )

# # # Use rich Live for real-time updates
# # layout = create_layout()

# # with Live(layout, console=console, refresh_per_second=4) as live:
# #     for idx, item in enumerate(stream_prompt_completion):
# #         for choice in item.choices:
# #             if "content" in choice.delta:
# #                 # Append content to the appropriate buffer
# #                 buffers[choice.index] += choice.delta["content"]

# #         # Update the layout periodically (every 10 streamed responses)
# #         if idx % 10 == 0:
# #             update_layout(layout)

# #     # Final print of all buffers
# #     update_layout(layout)

# from portkey_ai import Portkey
# import textwrap
# from rich.console import Console
# from rich.live import Live
# from rich.layout import Layout
# from rich.panel import Panel

# # Initialize Portkey client with API key
# client = Portkey(
#     api_key="YGYPNo/brTCeuBU7iE9vbvyOnAFM"  # Replace with actual API key or use env variables
# )

# # Set up console for rich output
# console = Console()

# # Number of streams/buffers
# NUM_STREAMS = 4
# buffers = [""] * NUM_STREAMS

# # Prompt ID for generating plan
# GENERATE_PLAN = "pp-generate-p-f4a0de"

# # Function to dynamically calculate max width based on the longest line
# def calculate_max_width(buffer_text, min_width=20, max_width=80):
#     lines = buffer_text.split("\n")
#     max_length = max([len(line) for line in lines] + [min_width])
#     return min(max_length + 4, max_width)  # Add padding, limit to max width

# # Function to create a box around buffer content
# def generate_box_around_buffer(buffer_text, buffer_num, max_cols):
#     lines = buffer_text.split('\n')
#     top_bottom_border = '+' + '-' * (max_cols - 2) + '+'
#     boxed_text = [top_bottom_border]
#     boxed_text.append(f"|{'Buffer ' + str(buffer_num):^{max_cols - 2}}|")
#     boxed_text.append(top_bottom_border)
    
#     for line in lines:
#         wrapped_lines = textwrap.wrap(line, width=max_cols - 4)
#         for wrapped_line in wrapped_lines:
#             padded_line = wrapped_line.ljust(max_cols - 4)
#             boxed_text.append(f"| {padded_line} |")
    
#     boxed_text.append(top_bottom_border)
#     return '\n'.join(boxed_text)

# # Function to print current buffers in a grid layout, dynamically adjusting column widths
# def create_layout():
#     layout = Layout()

#     # Dynamically split the layout into vertical columns
#     layout.split_row(
#         *[Layout(name=f"buffer{i + 1}") for i in range(NUM_STREAMS)]
#     )

#     return layout

# # Update layout with buffers and dynamically adjust each column width
# def update_layout(layout):
#     for i, buffer_content in enumerate(buffers):
#         max_width = calculate_max_width(buffer_content)  # Dynamically calculate width
#         buffer_box = Panel(buffer_content, title=f"Buffer {i + 1}", border_style="bold", width=max_width)
#         layout[f"buffer{i + 1}"].update(buffer_box)

# # Create streaming prompt completion with n parallel responses
# stream_prompt_completion = client.prompts.completions.create(
#     prompt_id=GENERATE_PLAN,
#     variables={"tools_available": "", "prompt": "Generate a multi-step plan for a project"},
#     stream=True,
#     n=NUM_STREAMS  # Request 4 completions in parallel
# )

# # Use rich Live for real-time updates
# layout = create_layout()

# with Live(layout, console=console, refresh_per_second=4) as live:
#     for idx, item in enumerate(stream_prompt_completion):
#         for choice in item.choices:
#             if "content" in choice.delta:
#                 # Append content to the appropriate buffer
#                 buffers[choice.index] += choice.delta["content"]

#         # Update the layout periodically (every 10 streamed responses)
#         if idx % 10 == 0:
#             update_layout(layout)

#     # Final print of all buffers
#     update_layout(layout)


from portkey_ai import Portkey
import textwrap
from rich.console import Console
from rich.live import Live
from rich.layout import Layout
from rich.panel import Panel

# Initialize Portkey client with API key
client = Portkey(
    api_key="YGYPNo/brTCeuBU7iE9vbvyOnAFM"  # Replace with actual API key or use env variables
)

# Set up console for rich output
console = Console()

# Number of streams/buffers
NUM_STREAMS = 4
buffers = [""] * NUM_STREAMS

# Prompt ID for generating plan
GENERATE_PLAN = "pp-generate-p-f4a0de"

# Function to dynamically calculate max width based on terminal size
def calculate_column_width(total_columns, padding=4):
    # Get terminal dimensions
    terminal_width = console.size.width
    column_width = (terminal_width - (padding * total_columns)) // total_columns
    return column_width

# Function to create a box around buffer content
def generate_box_around_buffer(buffer_text, buffer_num, max_cols):
    lines = buffer_text.split('\n')
    top_bottom_border = '+' + '-' * (max_cols - 2) + '+'
    boxed_text = [top_bottom_border]
    boxed_text.append(f"|{'Buffer ' + str(buffer_num):^{max_cols - 2}}|")
    boxed_text.append(top_bottom_border)
    
    for line in lines:
        wrapped_lines = textwrap.wrap(line, width=max_cols - 4)
        for wrapped_line in wrapped_lines:
            padded_line = wrapped_line.ljust(max_cols - 4)
            boxed_text.append(f"| {padded_line} |")
    
    boxed_text.append(top_bottom_border)
    return '\n'.join(boxed_text)

# Function to print current buffers in a grid layout, dynamically adjusting column widths
def create_layout():
    layout = Layout()

    # Dynamically split the layout into vertical columns
    layout.split_row(
        *[Layout(name=f"buffer{i + 1}") for i in range(NUM_STREAMS)]
    )

    return layout

# Update layout with buffers and dynamically adjust each column width
def update_layout(layout):
    column_width = calculate_column_width(NUM_STREAMS)
    for i, buffer_content in enumerate(buffers):
        buffer_box = Panel(buffer_content, title=f"Buffer {i + 1}", border_style="bold", width=column_width)
        layout[f"buffer{i + 1}"].update(buffer_box)

# Create streaming prompt completion with n parallel responses
stream_prompt_completion = client.prompts.completions.create(
    prompt_id=GENERATE_PLAN,
    variables={"tools_available": "", "prompt": "Generate a multi-step plan for a project"},
    stream=True,
    n=NUM_STREAMS  # Request 4 completions in parallel
)

# Use rich Live for real-time updates
layout = create_layout()

with Live(layout, console=console, refresh_per_second=4) as live:
    for idx, item in enumerate(stream_prompt_completion):
        for choice in item.choices:
            if "content" in choice.delta:
                # Append content to the appropriate buffer
                buffers[choice.index] += choice.delta["content"]

        # Update the layout periodically (every 10 streamed responses)
        if idx % 1 == 0:
            update_layout(layout)

    # Final print of all buffers
    update_layout(layout)


INFO:httpx:HTTP Request: POST https://api.portkey.ai/v1/prompts/pp-generate-p-f4a0de/completions "HTTP/1.1 200 OK"


Output()